In [5]:
from sentence_transformers import SentenceTransformer

In [ ]:
from huggingface_hub import login

login()

In [6]:
model = SentenceTransformer('Qwen/Qwen3-Embedding-0.6B', device='cuda')

Loading weights: 100%|██████████| 310/310 [00:01<00:00, 303.17it/s]


In [7]:
from tqdm import tqdm

In [ ]:
import lancedb

db = lancedb.connect("lancedb")

In [ ]:
import pandas as pd

In [ ]:
import numpy as np

In [ ]:

from datasets import load_dataset

dataset_name, subject = "xlangai/BRIGHT", "biology"
path = "data/BRIGHT/biology"

docs = load_dataset(dataset_name, "long_documents")[subject]
chunks = load_dataset(dataset_name, "documents")[subject]
evals = load_dataset(dataset_name, "examples")[subject]


In [ ]:
import gc
import torch
import numpy as np
from tqdm.auto import tqdm

# --------------------------------------------------------------------------
# 1) Textes + longueur "proxy" (caractères) pour trier/bucketer
# --------------------------------------------------------------------------
all_texts = chunks["content"]
all_ids   = chunks["id"]
n = len(all_texts)

lengths = np.array([len(t) for t in all_texts], dtype=np.int64)

try:
    embedding_dim = model.get_sentence_embedding_dimension()
except AttributeError:
    embedding_dim = model.encode(["test"], convert_to_numpy=True).shape[1]

# Tableau pré-alloué : l'ordre original du dataset est préservé,
# pas besoin de dict par id -> l'index numérique EST déjà l'id de position.
vectors = np.empty((n, embedding_dim), dtype=np.float32)
done_mask = np.zeros(n, dtype=bool)

device = model.device

# --------------------------------------------------------------------------
# 2) Construction de batches dynamiques par "budget" (bin-packing glouton)
# --------------------------------------------------------------------------
MAX_LOAD_PER_BATCH = 20_000  # taille_batch * longueur_max -> à tuner (cf. plus bas)
MAX_BATCH_SIZE = 64          # plafond même pour les tout petits textes

def build_dynamic_batches(lengths, max_load, max_bs):
    order = np.argsort(-lengths)  # du plus long au plus court
    batches, cur, cur_max_len = [], [], 0
    for idx in order:
        L = lengths[idx]
        new_max_len = max(cur_max_len, L)
        new_size = len(cur) + 1
        if cur and (new_size * new_max_len > max_load or new_size > max_bs):
            batches.append(cur)
            cur, cur_max_len = [idx], L
        else:
            cur.append(idx)
            cur_max_len = new_max_len
    if cur:
        batches.append(cur)
    return batches

batches = build_dynamic_batches(lengths, MAX_LOAD_PER_BATCH, MAX_BATCH_SIZE)
sizes = [len(b) for b in batches]
print(f"{len(batches)} batches pour {n} textes (taille min={min(sizes)}, max={max(sizes)})")

# --------------------------------------------------------------------------
# 3) Encodage avec écriture directe (fancy indexing) + retry OOM
# --------------------------------------------------------------------------
model.eval()

def encode_with_retry(texts):
    try:
        return model.encode(
            texts,
            batch_size=len(texts),
            convert_to_numpy=True,
            normalize_embeddings=True,
            show_progress_bar=False,
            truncate_dim=None,
        )
    except RuntimeError as e:
        if "out of memory" not in str(e).lower():
            raise
        torch.cuda.empty_cache()
        gc.collect()
        if len(texts) == 1:
            print("⚠️  OOM même en batch=1, fallback CPU pour ce document.")
            model.to("cpu")
            out = model.encode(
                texts, batch_size=1, convert_to_numpy=True,
                normalize_embeddings=True, show_progress_bar=False,
            )
            model.to(device)
            return out
        mid = len(texts) // 2
        return np.vstack([
            encode_with_retry(texts[:mid]),
            encode_with_retry(texts[mid:]),
        ])

with torch.inference_mode():
    for step, batch_idx in enumerate(tqdm(batches, desc="Embedding")):
        batch_texts = [all_texts[i] for i in batch_idx]
        batch_vectors = encode_with_retry(batch_texts)

        vectors[batch_idx] = batch_vectors      # <- injection à la volée, sans dict par id
        done_mask[batch_idx] = True

        if step % 20 == 0:
            gc.collect()
            torch.cuda.empty_cache()

assert done_mask.all(), f"{(~done_mask).sum()} vecteurs manquants !"
print("Terminé :", vectors.shape)

In [ ]:
vectors

In [ ]:
embedded_chunks = []
for vector, chunk in zip(vectors, chunks):
    embedded_chunks.append(
        {
            "id": chunk["id"],
            "content": chunk["content"],
            "vector": vector.tolist()
        }
    )

In [ ]:
embedded_chunks

In [ ]:
embedded_chunks_df = pd.DataFrame(embedded_chunks)
embedded_chunks_df.to_csv(f"{path}/embedded_chunks.csv", index=False)

In [ ]:
import numpy as np

# Extraction de la liste des textes en s'assurant de convertir en chaîne
texts = [str(t) for t in chunks["content"] if t is not None]

# Calcul des longueurs en caractères et en mots
char_lengths = [len(t) for t in texts]
word_lengths = [len(t.split()) for t in texts]

# Identification du texte le plus long
max_char_index = int(np.argmax(char_lengths))
longest_text = texts[max_char_index]

# Statistiques globales
avg_chars = np.mean(char_lengths)
avg_words = np.mean(word_lengths)
max_chars = char_lengths[max_char_index]
max_words = word_lengths[max_char_index]

print(f"--- Statistiques du Dataset ---")
print(f"Nombre total de chunks : {len(texts)}")
print(f"Longueur moyenne       : {avg_chars:.2f} caractères ({avg_words:.1f} mots)")
print(f"Longueur maximale      : {max_chars} caractères ({max_words} mots)")
print(f"Index du texte le plus long : {max_char_index}\n")


In [ ]:
dataset_name = "xlangai/BRIGHT"
subject = "biology"

In [ ]:
path = "data/BRIGHT/" + subject
docs = pd.read_csv(f"{path}/embedded_chunks.csv")

In [ ]:
docs = docs.to_dict(orient="records")  # Convertir en liste de dictionnaires
docs

In [ ]:
import lancedb

In [ ]:
db = lancedb.connect(f"{path}/vanilladb")

In [ ]:
import re

for doc, vector in zip(docs, vectors):
    doc['parent_id'] = re.sub(r"_\d+_\d+\.txt$", ".txt", doc["id"])
    doc["vector"] = vector  # Convertir la chaîne en tableau numpy
docs

In [ ]:
table = db.create_table(
    "chunks",
    data=docs,
    mode="overwrite"
)

In [ ]:
query = """
Why do I only breathe out of one nostril?
I was just sitting with my hand next to my nose and I realized that air was only coming out of the right nostril. Why is that? I would think I would use both, it seems much more efficient. Have I always only been breathing out of my right nostril?
"""

query_vector = model.encode([query], convert_to_numpy=True, normalize_embeddings=True)[0]

In [ ]:
results = (
    table.search(query_vector)
    .limit(10)
    .select(["id"])
    .to_list()
)

In [ ]:
results

In [ ]:
evals[0]

In [8]:
import lancedb
import pandas as pd

path = "data/BRIGHT/biology"
db = lancedb.connect(f"{path}/vanilladb")

table = db.open_table('chunks')

evals = pd.read_csv(f"{path}/evals.csv").to_dict(orient="records")

In [9]:
import re

def parse_gold_ids(raw):
    if isinstance(raw, str):
        return re.findall(r"'([^']*)'", raw)
    return list(raw)  # deja une vraie liste/array, on ne touche pas

for example in evals:
    example["gold_ids"] = parse_gold_ids(example["gold_ids"])

In [10]:
print(type(evals[0]["gold_ids"]), evals[0]["gold_ids"])

<class 'list'> ['insects_attracted_to_light/Proximate_and_ultimate_causation_0.txt', 'insects_attracted_to_light/Proximate_and_ultimate_causation_1.txt', 'insects_attracted_to_light/Phototaxis_0.txt', 'insects_attracted_to_light/Phototaxis_3.txt', 'insects_attracted_to_light/Phototaxis_4.txt']


In [11]:
def average_precision(hits, n_relevant):
    """hits: liste de 0/1 dans l'ordre de retrieval, n_relevant = len(gold_ids)"""
    if n_relevant == 0:
        return None
    hits_so_far = 0
    precision_sum = 0.0
    for rank, is_hit in enumerate(hits, start=1):
        if is_hit:
            hits_so_far += 1
            precision_sum += hits_so_far / rank
    return precision_sum / n_relevant


MAP = 0
hit_points = 0
vanilla_results = []

for example in evals:
    query_vector = model.encode([example["query"]], convert_to_numpy=True, normalize_embeddings=True)[0]
    results = (
        table.search(query_vector)
        .limit(10)
        .select(["id"])
        .to_list()
    )
    gold_ids = set(example["gold_ids"])
    n = len(gold_ids)

    result_copy = dict(example)
    result_copy["ids_found"] = results
    hits = [1 if r["id"] in gold_ids else 0 for r in results]
    result_copy["hits"] = hits

    ap = average_precision(hits, n)
    result_copy["ap"] = ap
    MAP += ap or 0

    found = sum(hits)
    result_copy["hit_points"] = found / n
    hit_points += found / n

    vanilla_results.append(result_copy)

MAP /= len(evals)
hit_points /= len(evals)

[2026-09-10T05:01:12Z WARN  lance::dataset::scanner] Deprecation warning, this behavior will change in the future. This search specified output columns but did not include `_distance`.  Currently the `_distance` column will be included.  In the future it will not.  Call `disable_scoring_autoprojection` to adopt the future behavior and avoid this warning
[2026-09-10T05:01:13Z WARN  lance::dataset::scanner] Deprecation warning, this behavior will change in the future. This search specified output columns but did not include `_distance`.  Currently the `_distance` column will be included.  In the future it will not.  Call `disable_scoring_autoprojection` to adopt the future behavior and avoid this warning
[2026-09-10T05:01:13Z WARN  lance::dataset::scanner] Deprecation warning, this behavior will change in the future. This search specified output columns but did not include `_distance`.  Currently the `_distance` column will be included.  In the future it will not.  Call `disable_scoring_

In [12]:
print(MAP, hit_points)

0.06571240877066119 0.1483498701945304


In [13]:
path = "data/BRIGHT/biology"

In [14]:
vanilla_results_df = pd.DataFrame(vanilla_results)
vanilla_results_df.to_csv(path + "/vanilla_results.csv", index=False, encoding="utf-8")

In [ ]:
example = evals[0]
query_vector = model.encode([example["query"]], convert_to_numpy=True, normalize_embeddings=True)[0]
results = table.search(query_vector).limit(10).select(["id"]).to_list()

print("gold_ids:", example["gold_ids"])
print("types gold_ids:", [type(x) for x in example["gold_ids"]])
print("retrieved ids:", [r["id"] for r in results])
print("types retrieved:", [type(r["id"]) for r in results])

# Print

In [33]:
import pandas as pd

vanilla_results = pd.read_csv(path + "/vanilla_results.csv").to_dict(orient="records")

In [9]:
vanilla_results

[{'query': 'Claim in article about why insects are attracted to light\nIn this article they are addressing the reason insects are attracted to light when they say\nHeat radiation as an attractive component is refuted by the effect of LED lighting, which supplies negligible infrared radiation yet still entraps vast numbers of insects.\nI don\'t see why attraction to LEDs shows they\'re not seeking heat. Could they for example be evolutionarily programmed to associate light with heat? So that even though they don\'t encounter heat near/on the LEDs they still "expect" to?',
  'reasoning': 'The question probes why insects are drawn to low-heat LED lights, challenging the idea that their attraction to light is heat-based. The document helps distinguish between heat attraction and evolved behaviors, shedding light on why insects might be attracted to LEDs despite their minimal heat.',
  'id': 0,
  'excluded_ids': "['N/A']",
  'gold_ids_long': "['insects_attracted_to_light/Proximate_and_ultim

In [34]:

from datasets import load_dataset

dataset_name, subject = "xlangai/BRIGHT", "biology"
path = "data/BRIGHT/biology"

docs = load_dataset(dataset_name, "long_documents")[subject]
chunks = load_dataset(dataset_name, "documents")[subject]
evals = load_dataset(dataset_name, "examples")[subject]


In [44]:
import ast
import re


def parse_ids(value):
    if isinstance(value, (list, tuple, set)):
        return [str(item) for item in value]

    if value is None:
        return []

    value = str(value).strip()

    try:
        parsed = ast.literal_eval(value)
        if isinstance(parsed, (list, tuple, set)):
            return [str(item) for item in parsed]
    except (SyntaxError, ValueError):
        pass

    # Supporte le format NumPy : ['id_1' 'id_2']
    return [
        first or second
        for first, second in re.findall(
            r"'([^']*)'|\"([^\"]*)\"",
            value,
        )
    ]


def check_ids_in_docs(ids_to_check, docs):
    ids_to_check = parse_ids(ids_to_check)
    doc_ids = {str(doc["id"]) for doc in docs}

    return {
        "present": [
            item_id for item_id in ids_to_check
            if item_id in doc_ids
        ],
        "missing": [
            item_id for item_id in ids_to_check
            if item_id not in doc_ids
        ],
    }

In [45]:
result = check_ids_in_docs(
    vanilla_results[0]["gold_ids_long"],
    docs,
)

print("Présents :", result["present"])
print("Absents :", result["missing"])

Présents : []
Absents : ['insects_attracted_to_light/Proximate_and_ultimate_causation.txtinsects_attracted_to_light/Phototaxis.txt']


In [48]:
import ast
import re
from html import escape
from IPython.display import display, HTML


def _parse_list(value):
    if isinstance(value, (list, tuple, set)):
        return list(value)

    if value is None:
        return []

    text = str(value).strip()

    try:
        parsed = ast.literal_eval(text)
        if isinstance(parsed, (list, tuple, set)):
            return list(parsed)
    except (SyntaxError, ValueError):
        pass

    return re.findall(r"""['"]([^'"]+)['"]""", text)


def _find_known_ids(value, known_ids):
    if isinstance(value, (list, tuple, set)):
        value = " ".join(str(item) for item in value)

    text = str(value)

    return [
        item_id
        for item_id in sorted(
            {str(item) for item in known_ids},
            key=len,
            reverse=True,
        )
        if item_id in text
    ]


def clean_display_text(value):
    text = str(value)

    # Normaliser les retours à la ligne
    text = text.replace("\r\n", "\n").replace("\r", "\n")

    # Supprimer les espaces en fin de ligne
    text = re.sub(r"[ \t]+$", "", text, flags=re.MULTILINE)

    # Autoriser au maximum deux sauts de ligne consécutifs
    text = re.sub(r"\n{3,}", "\n\n", text)

    return text.strip()


def display_result(result, mask_doc=False):
    result = dict(result)

    doc_ids = [doc["id"] for doc in docs]
    chunk_ids = [chunk["id"] for chunk in chunks]

    gold_ids_long = _find_known_ids(
        result.get("gold_ids_long"),
        doc_ids,
    )

    gold_ids = _find_known_ids(
        result.get("gold_ids"),
        chunk_ids,
    )

    ids_found = _parse_list(result.get("ids_found"))
    hits = _parse_list(result.get("hits"))

    docs_by_id = {
        str(doc["id"]): clean_display_text(doc["content"])
        for doc in docs
    }

    chunks_by_id = {
        str(chunk["id"]): clean_display_text(chunk["content"])
        for chunk in chunks
    }

    colors = {
        "title": "#4A90E2",
        "id": "#E67E22",
        "query": "#D35400",
        "metric": "#27AE60",
        "rank": "#9B59B6",
        "distance": "#16A085",
    }

    def title(text):
        return (
            f'<h3 style="color:{colors["title"]}; '
            f'margin-top:20px; margin-bottom:8px;">'
            f"{escape(text)}</h3>"
        )

    def colored(text, color):
        return (
            f'<span style="color:{color}; font-weight:bold">'
            f"{escape(str(text))}</span>"
        )

    def block(content):
        return (
            '<div style="white-space:pre-wrap; '
            'font-family:monospace; '
            'margin-left:12px; '
            'margin-bottom:16px; '
            'line-height:1.45;">'
            f"{escape(clean_display_text(content))}"
            "</div>"
        )

    html = []

    html.append(
        f'{colored("Query:", colors["query"])} '
        f'{escape(clean_display_text(result.get("query", "")))}'
    )

    if not mask_doc:
        html.append(title("Full document contents"))

        for doc_id in gold_ids_long:
            doc_id = str(doc_id)

            html.append(
                f'{colored("ID:", colors["id"])} '
                f'{colored(doc_id, colors["id"])}'
            )

            html.append(
                block(docs_by_id.get(doc_id, "[Document not found]"))
            )

    html.append(title("Gold IDs"))

    for chunk_id in gold_ids:
        chunk_id = str(chunk_id)

        html.append(
            f'{colored("ID:", colors["id"])} '
            f'{colored(chunk_id, colors["id"])}'
        )

        html.append(
            block(chunks_by_id.get(chunk_id, "[Chunk not found]"))
        )

    html.append(title("Found IDs"))

    for rank, item in enumerate(ids_found, start=1):
        if isinstance(item, str):
            try:
                item = ast.literal_eval(item)
            except (SyntaxError, ValueError):
                continue

        if not isinstance(item, dict):
            continue

        chunk_id = str(item.get("id", "N/A"))
        distance = item.get("_distance", "N/A")

        html.append(
            f'{colored(f"Rank: top {rank}", colors["rank"])} '
            f'{colored("ID:", colors["id"])} '
            f'{colored(chunk_id, colors["id"])} '
            f'{colored("Distance:", colors["distance"])} '
            f'{escape(str(distance))}'
        )

        html.append(
            block(chunks_by_id.get(chunk_id, "[Chunk not found]"))
        )

    html.append(title("Evaluation"))

    html.append(
        f'{colored("Hits:", colors["metric"])} '
        f'{escape(str(hits))}<br>'
        f'{colored("Average Precision:", colors["metric"])} '
        f'{escape(str(result.get("ap", "N/A")))}<br>'
        f'{colored("Hit Points:", colors["metric"])} '
        f'{escape(str(result.get("hit_points", "N/A")))}'
    )

    print(
        f"Documents gold trouvés : {len(gold_ids_long)} | "
        f"Chunks gold trouvés : {len(gold_ids)}"
    )

    display(HTML("\n".join(html)))

In [49]:
display_result(vanilla_results[0])

Documents gold trouvés : 2 | Chunks gold trouvés : 5


# context Retrivial

In [ ]:
import gc
import torch
import numpy as np
from tqdm.auto import tqdm

# --------------------------------------------------------------------------
# 1) Textes + longueur "proxy" (caractères) pour trier/bucketer
# --------------------------------------------------------------------------
all_texts = chunks["content"]
all_ids   = chunks["id"]
n = len(all_texts)

lengths = np.array([len(t) for t in all_texts], dtype=np.int64)

try:
    embedding_dim = model.get_sentence_embedding_dimension()
except AttributeError:
    embedding_dim = model.encode(["test"], convert_to_numpy=True).shape[1]

# Tableau pré-alloué : l'ordre original du dataset est préservé,
# pas besoin de dict par id -> l'index numérique EST déjà l'id de position.
vectors = np.empty((n, embedding_dim), dtype=np.float32)
done_mask = np.zeros(n, dtype=bool)

device = model.device

# --------------------------------------------------------------------------
# 2) Construction de batches dynamiques par "budget" (bin-packing glouton)
# --------------------------------------------------------------------------
MAX_LOAD_PER_BATCH = 20_000  # taille_batch * longueur_max -> à tuner (cf. plus bas)
MAX_BATCH_SIZE = 64          # plafond même pour les tout petits textes

def build_dynamic_batches(lengths, max_load, max_bs):
    order = np.argsort(-lengths)  # du plus long au plus court
    batches, cur, cur_max_len = [], [], 0
    for idx in order:
        L = lengths[idx]
        new_max_len = max(cur_max_len, L)
        new_size = len(cur) + 1
        if cur and (new_size * new_max_len > max_load or new_size > max_bs):
            batches.append(cur)
            cur, cur_max_len = [idx], L
        else:
            cur.append(idx)
            cur_max_len = new_max_len
    if cur:
        batches.append(cur)
    return batches

batches = build_dynamic_batches(lengths, MAX_LOAD_PER_BATCH, MAX_BATCH_SIZE)
sizes = [len(b) for b in batches]
print(f"{len(batches)} batches pour {n} textes (taille min={min(sizes)}, max={max(sizes)})")

# --------------------------------------------------------------------------
# 3) Encodage avec écriture directe (fancy indexing) + retry OOM
# --------------------------------------------------------------------------
model.eval()

def encode_with_retry(texts):
    try:
        return model.encode(
            texts,
            batch_size=len(texts),
            convert_to_numpy=True,
            normalize_embeddings=True,
            show_progress_bar=False,
            truncate_dim=None,
        )
    except RuntimeError as e:
        if "out of memory" not in str(e).lower():
            raise
        torch.cuda.empty_cache()
        gc.collect()
        if len(texts) == 1:
            print("⚠️  OOM même en batch=1, fallback CPU pour ce document.")
            model.to("cpu")
            out = model.encode(
                texts, batch_size=1, convert_to_numpy=True,
                normalize_embeddings=True, show_progress_bar=False,
            )
            model.to(device)
            return out
        mid = len(texts) // 2
        return np.vstack([
            encode_with_retry(texts[:mid]),
            encode_with_retry(texts[mid:]),
        ])

with torch.inference_mode():
    for step, batch_idx in enumerate(tqdm(batches, desc="Embedding")):
        batch_texts = [all_texts[i] for i in batch_idx]
        batch_vectors = encode_with_retry(batch_texts)

        vectors[batch_idx] = batch_vectors      # <- injection à la volée, sans dict par id
        done_mask[batch_idx] = True

        if step % 20 == 0:
            gc.collect()
            torch.cuda.empty_cache()

assert done_mask.all(), f"{(~done_mask).sum()} vecteurs manquants !"
print("Terminé :", vectors.shape)

In [3]:
from datasets import load_dataset

dataset_name, subject = "xlangai/BRIGHT", "biology"

docs = load_dataset(dataset_name, "long_documents")[subject]
chunks = load_dataset(dataset_name, "documents")[subject]
evals = load_dataset(dataset_name, "examples")[subject]

text_to_print = f"""
docs: {docs[0]['id']} (docs contain content column too, but too long to display)
chunks: {chunks[0]}
evals: {evals[0]}
"""

print(text_to_print)


docs: protein_in_food/Protein_folding.txt (docs contain content column too, but too long to display)
chunks: {'id': 'neanderthals_vitamin_C_diet/Neanderthal_0_43.txt', 'content': ' pelvises; and proportionally shorter forearms and forelegs.\nBased on 45 Neanderthal long bones from 14 men and 7 women, the average height was 164 to 168\xa0cm (5\xa0ft 5\xa0in to 5\xa0ft 6\xa0in) for males and 152 to 156\xa0cm (5\xa0ft 0\xa0in to 5\xa0ft 1\xa0in) for females. For comparison, the average height of 20 males and 10 females Upper Palaeolithic humans is, respectively, 176.2\xa0cm (5\xa0ft 9.4\xa0in) and 162.9'}
evals: {'query': 'Claim in article about why insects are attracted to light\nIn this article they are addressing the reason insects are attracted to light when they say\nHeat radiation as an attractive component is refuted by the effect of LED lighting, which supplies negligible infrared radiation yet still entraps vast numbers of insects.\nI don\'t see why attraction to LEDs shows they

In [4]:
len(evals)

103

In [22]:
docs[0]["id"], chunks[0]

('protein_in_food/Protein_folding.txt',
 {'id': 'neanderthals_vitamin_C_diet/Neanderthal_0_43.txt',
  'content': ' pelvises; and proportionally shorter forearms and forelegs.\nBased on 45 Neanderthal long bones from 14 men and 7 women, the average height was 164 to 168\xa0cm (5\xa0ft 5\xa0in to 5\xa0ft 6\xa0in) for males and 152 to 156\xa0cm (5\xa0ft 0\xa0in to 5\xa0ft 1\xa0in) for females. For comparison, the average height of 20 males and 10 females Upper Palaeolithic humans is, respectively, 176.2\xa0cm (5\xa0ft 9.4\xa0in) and 162.9'})

In [ ]:
import lancedb

path = "data/BRIGHT/" + subject
db = lancedb.connect(f"{path}/vanilladb")
table = db.open_table('chunks')

In [2]:
chunk = chunks[0]
chunk

{'id': 'neanderthals_vitamin_C_diet/Neanderthal_0_43.txt',
 'content': ' pelvises; and proportionally shorter forearms and forelegs.\nBased on 45 Neanderthal long bones from 14 men and 7 women, the average height was 164 to 168\xa0cm (5\xa0ft 5\xa0in to 5\xa0ft 6\xa0in) for males and 152 to 156\xa0cm (5\xa0ft 0\xa0in to 5\xa0ft 1\xa0in) for females. For comparison, the average height of 20 males and 10 females Upper Palaeolithic humans is, respectively, 176.2\xa0cm (5\xa0ft 9.4\xa0in) and 162.9'}

In [ ]:
import re
parent_id = re.sub(r"_\d+_\d+\.txt$", ".txt", chunk["id"])

TypeError: sub() missing 1 required positional argument: 'string'

In [ ]:
parent_id

'neanderthals_vitamin_C_diet/Neanderthal.txt'

In [18]:
result = chunks.filter(lambda chunk: parent_id in chunk["id"])

Filter: 100%|██████████| 57359/57359 [00:00<00:00, 1163593.41 examples/s]


In [36]:
import re
from collections import defaultdict

pattern = re.compile(r"_\d+_\d+\.txt$")

# 1. Regrouper les chunks par leur doc parent (une seule passe, O(n))
chunks_by_parent = defaultdict(list)
for chunk in chunks:
    parent_id = pattern.sub(".txt", chunk["id"])
    chunks_by_parent[parent_id].append(chunk)

# 2. Construire la liste de dicts {doc, chunks}
texts = [
    {"doc": doc, "chunks": chunks_by_parent.get(doc["id"], [])}
    for doc in docs
]

In [28]:
texts

[{'doc': {'id': 'protein_in_food/Protein_folding.txt',
   'content': 'Protein folding is the physical process by which a protein, after synthesis by a ribosome as a linear chain of amino acids, changes from an unstable random coil into a more ordered three-dimensional structure. This structure permits the protein to become biologically functional.\nThe folding of many proteins begins even during the translation of the polypeptide chain. The amino acids interact with each other to produce a well-defined three-dimensional structure, known as the protein\'s native state. This structure is determined by the amino-acid sequence or primary structure.\nThe correct three-dimensional structure is essential to function, although some parts of functional proteins may remain unfolded, indicating that protein dynamics are important. Failure to fold into a native structure generally produces inactive proteins, but in some instances, misfolded proteins have modified or toxic functionality. Several ne

In [ ]:
table.search().where(f"id = '{chunk["id"]}'").select(["id", "parent_id"]).to_list()

In [46]:
SYSTEM_PROMPT = """
You are a document-chunk contextualization engine that prepares chunks for semantic (vector) search retrieval.

INPUT
1. FULL SOURCE DOCUMENT — the complete source text (reference only).
2. TARGET CHUNK — the exact excerpt to rewrite.

TASK
Rewrite the TARGET CHUNK to be maximally self-contained and retrieval-rich, using ONLY facts explicitly present in the FULL SOURCE DOCUMENT. Be extractive about facts (only surface what the document states) and generative about phrasing (reword and integrate freely).

===================================
HARD BOUNDARY — NEVER OVERLAP NEIGHBORING CHUNKS
===================================
The TARGET CHUNK's start and end are fixed positions. You are enriching it, not growing it.

- If the chunk ends mid-sentence, do NOT complete it with text that follows in the source — even if that text is one word away.
  Example: chunk ends "...where alpha helices can form" → do not add how alpha helices form, even though the very next sentence explains it.
- If the chunk begins mid-fragment, you may clarify what the fragment refers to, but do NOT prepend the missing preceding text.
- Never add a next sentence, paragraph, example, process step, explanation, or definition just because it sits next to the chunk in the source — proximity is not justification.

Test before adding anything: would this addition still be useful if the TARGET CHUNK were moved to a completely different position in the document?
- Yes → it's disambiguating context, allowed.
- No (it's only useful because it's adjacent text) → forbidden, discard it.

===================================
WHAT TO ENRICH WITH (only if explicitly supported by the source)
===================================
- Resolve every pronoun, demonstrative, or vague reference ("it", "this", "the above", "the company", "that clause", "the former/latter"...) into the explicit noun/name/date/entity it points to.
- Spell out acronyms/abbreviations using the expansion given elsewhere in the document.
- Make implicit subjects, actors, dates, locations, or conditions explicit when the document states them elsewhere but the chunk only assumes them.
- Name the section, heading, topic, or stage of the document the chunk belongs to — but ONLY if that exact heading text appears verbatim in the source; never invent or guess a plausible-sounding title.
- Surface directly relevant named entities/terminology from elsewhere in the document that help situate or disambiguate the chunk, even if not literally present in the TARGET CHUNK — but only terms that actually appear in the document, never synonyms or related concepts from your own knowledge.

Do not pad the chunk with generic, document-level filler that would apply equally to any other chunk of the same document (a restated theme with no chunk-specific disambiguating value).

===================================
ANTI-HALLUCINATION — HARD LIMITS
===================================
- Never introduce a fact, number, date, name, term, or claim that is not explicitly present — verbatim or as clear paraphrase — in the FULL SOURCE DOCUMENT. This applies even if you're confident it's true in the real world (e.g. a textbook fact you happen to know): if it's not in the document, it does not go in the output.
- Never guess a section/heading name that isn't verbatim in the source.
- If something in the TARGET CHUNK is ambiguous and cannot be resolved from the FULL SOURCE DOCUMENT, leave it exactly as it is rather than guessing.

===================================
PRESERVE THE TARGET CHUNK
===================================
Every clause and fact from the original TARGET CHUNK must remain in the output, in full — including sentence fragments that look incomplete because the chunk was cut mid-sentence. Do not drop, shorten, summarize, or "clean up" the original content. Do not repair a truncated chunk by importing neighboring text (see HARD BOUNDARY above).

===================================
SELF-CHECK BEFORE ANSWERING
===================================
1. Coverage — is every fact/clause of the original TARGET CHUNK still present, including leading/trailing fragments?
2. Boundary — did I complete a truncated sentence, or add a next sentence/paragraph/example from neighboring text? If yes, remove it.
3. Grounding — for every addition, can I point to the specific sentence(s) in the FULL SOURCE DOCUMENT that support it? If not, remove it.

===================================
LANGUAGE
===================================
Always output in English. If the source is in another language, translate faithfully, preserving all facts and nuance. Keep proper nouns in their original form, optionally followed by a brief English clarification in parentheses on first use.

===================================
LENGTH
===================================
No fixed length ratio. Let enrichment be dictated entirely by how much genuinely relevant, document-grounded, chunk-specific context actually exists — not by a target length.

===================================
OUTPUT FORMAT
===================================
Return ONLY the rewritten TARGET CHUNK, ready to embed as-is. No preamble, no explanation, no labels, no markdown code fences, no quotation marks. If no safe enrichment is possible, return the TARGET CHUNK unchanged (translated to English if necessary).

""".strip()

In [47]:
from openai import OpenAI
import pandas as pd
import os
from tqdm import tqdm

path = "data/BRIGHT/biology"
csv_path = f"{path}/context_chunks.csv"

os.makedirs(path, exist_ok=True)

# 1. Charger les ids déjà traités (si le fichier existe déjà)
if os.path.exists(csv_path):
    done_df = pd.read_csv(csv_path)
    done_ids = set(done_df["id"].astype(str))
    print(f"{len(done_ids)} chunks déjà traités, ils seront ignorés.")
else:
    done_ids = set()

# 2. Client créé une seule fois
client = OpenAI(
    base_url="http://127.0.0.1:8080/v1",
    api_key="none"
)

for text in tqdm(texts):
    doc = text["doc"]

    for chunk in text["chunks"]:
        # 3. On saute les chunks déjà présents dans le CSV
        if str(chunk["id"]) in done_ids:
            continue

        prompt = f"""
        <document>
        {doc["content"]}
        </document>
        
        <chunk>
        {chunk["content"]}
        </chunk>
        """.strip()
        
        response = client.chat.completions.create(
            model="local-model",
            messages=[
                {"role": "system", "content": SYSTEM_PROMPT},
                {"role": "user", "content": prompt}
            ],
            temperature=0.1,
        )

        new_chunk = {
            "id": chunk["id"],
            "content": chunk["content"],
            "refined_content": response.choices[0].message.content,
            "parent_id": doc["id"]
        }

        pd.DataFrame([new_chunk]).to_csv(
            csv_path,
            mode='a',
            header=not os.path.exists(csv_path),
            index=False
        )

        # 4. Important : marquer cet id comme traité immédiatement,
        # sinon si le script plante en cours de doc, il pourrait le retraiter
        done_ids.add(str(chunk["id"]))


  0%|          | 0/524 [12:28<?, ?it/s]


KeyboardInterrupt: 

In [30]:
from openai import OpenAI
from tqdm import tqdm
formated_docs = []

for doc in tqdm(docs):
    client = OpenAI(
        base_url="http://127.0.0.1:8080/v1",
        api_key="none"
    )

    response = client.chat.completions.create(
        model="local-model",
        messages=[
            {"role": "system", "content": SYSTEM_PROMPT},
            {"role": "user", "content": doc["content"] }
        ],
        extra_body={
            "chat_template_kwargs": {"enable_thinking": False}
        },
        temperature=0.1,
    )

    formated_docs.append({
        "id": doc["id"],
        "content": response.choices[0].message.content
    })

 21%|██        | 108/524 [3:31:15<13:33:45, 117.37s/it]


APITimeoutError: Request timed out.

In [36]:
import pandas as pd

path = "data/BRIGHT/biology/formated_docs.csv"

formated_docs_df = pd.DataFrame(formated_docs)
formated_docs_df.to_csv(path, index=False, encoding="utf-8")

In [38]:
formated_docs_df = pd.read_csv(path)
formated_docs = formated_docs_df.to_dict(orient="records")

for i in tqdm(range(len(formated_docs), len(docs))):
    retry = 10
    doc = docs[i]
    
    for attempt in range(retry):
        try:
            client = OpenAI(
                base_url="http://127.0.0.1:8080/v1",
                api_key="none"
            )
        
            response = client.chat.completions.create(
                model="local-model",
                messages=[
                    {"role": "system", "content": SYSTEM_PROMPT},
                    {"role": "user", "content": doc["content"] }
                ],
                extra_body={
                    "chat_template_kwargs": {"enable_thinking": False}
                },
                temperature=0.1,
            )
        
            new_row = {
                "id": doc["id"],
                "content": response.choices[0].message.content
            }
            pd.DataFrame([new_row]).to_csv(path, mode='a', header=False, index=False, encoding="utf-8")
            
            break
        
        except Exception as e:
            print(f"Attempt {attempt + 1} failed for doc {doc['id']}: {e}")
            if attempt == retry - 1:
                raise e

  0%|          | 0/416 [00:00<?, ?it/s]

Attempt 1 failed for doc induce_sleep/Adenosinetriphosphat.txt: Request timed out.


  0%|          | 0/416 [34:54<?, ?it/s]


KeyboardInterrupt: 

In [20]:
doc = """
* Health Conditions
* Health Conditions
* [ Alzheimer's & Dementia ](/alzheimers-and-dementia)
* [ Anxiety ](/anxiety)
* [ Asthma & Allergies ](/asthma-and-allergies)
* [ Atopic Dermatitis ](/program/investigating-atopic-dermatitis)
* [ Breast Cancer ](/breast-cancer)
* [ Cancer ](/cancer)
* [ Cardiovascular Health ](/cardiovascular-health)
* [ COVID-19 ](/coronavirus?correlationId=2b137d5a-dcfb-464e-9ea6-72c5a54b4e92)
* [ Diabetes ](/diabetes)
* [ Environment & Sustainability ](/environment-and-sustainability)
* [ Exercise & Fitness ](/exercise-and-fitness)
* [ Eye Health ](/eye-health)
* [ Headache & Migraine ](/headache-and-migraine)
* [ Health Equity ](/health-equity)
* [ HIV & AIDS ](/hiv-and-aids)
* [ Human Biology ](/human-biology)
* [ Leukemia ](/leukemia)
* [ LGBTQIA+ ](/LGBTQIA)
* [ Men's Health ](/mens-health)
* [ Mental Health ](/mental-health)
* [ Multiple Sclerosis (MS) ](/multiple-sclerosis)
* [ Nutrition ](/nutrition)
* [ Parkinson's Disease ](/parkinsons-disease)
* [ Psoriasis ](/program/a-deeper-look-at-psoriasis)
* [ Psoriatic Arthritis ](/program/beneath-the-surface-with-psoriatic-arthritis)
* [ Sexual Health ](/sexual-health)
* [ Ulcerative Colitis ](/program/investigating-ulcerative-colitis)
* [ Women's Health ](/womens-health)
* Health Products
* [ Health Products ](/products-and-reviews)
* [ Nutrition & Fitness ](/products-and-reviews/nutrition-and-fitness-products)
* [ Vitamins & Supplements ](/products-and-reviews/vitamin-and-supplement-products)
* [ CBD ](/products-and-reviews/cbd-products)
* [ Sleep ](/products-and-reviews/sleep-products)
* [ Mental Health ](/products-and-reviews/mental-health-services-and-products)
* [ At-Home Testing ](/products-and-reviews/at-home-testing-products)
* [ Men’s Health ](/products-and-reviews/mens-health-products)
* [ Women’s Health ](/products-and-reviews/womens-health-products)
* Discover
* News
* [ Latest News ](/news)
* Original Series
* [ Medical Myths ](/content-series/medical-myths)
* [ Honest Nutrition ](/content-series/honest-nutrition)
* [ Through My Eyes ](/content-series/through-my-eyes)
* [ New Normal Health ](/content-series/new-normal-health)
* [ Podcasts ](/articles/in-conversation-podcast)
* [ 2023 in medicine ](/articles/2023-in-medicine-artificial-sweeteners-colon-cancer-male-birth-control)
* [ Why exercise is key to living a long and healthy life ](/articles/in-conversation-why-exercise-is-key-to-living-a-long-and-healthy-life)
* [ What do we know about the gut microbiome in IBD? ](/articles/in-conversation-what-do-we-know-about-the-gut-microbiome-in-ibd)
* [ My podcast changed me ](/articles/in-conversation-my-podcast-changed-me)
* [ Can 'biological race' explain disparities in health? ](/articles/in-conversation-can-biological-race-explain-disparities-in-health)
* [ Why Parkinson's research is zooming in on the gut ](/articles/in-conversation-why-parkinsons-research-is-zooming-in-on-the-gut)
* Tools
* General Health
* [ Drugs A-Z ](/drugs)
* [ Health Hubs ](/articles/content-hubs)
* Health Tools
* [ Find a Doctor ](/provider-near-me)
* [ BMI Calculators and Charts ](/articles/323586)
* [ Blood Pressure Chart: Ranges and Guide ](/articles/327077)
* [ Breast Cancer: Self-Examination Guide ](/articles/316898)
* [ Sleep Calculator ](/articles/sleep-calculator)
* Quizzes
* [ RA Myths vs Facts ](/articles/science-fact-or-fiction-separating-ra-myths-from-facts#1)
* [ Type 2 Diabetes: Managing Blood Sugar ](/articles/managing-blood-sugar-type-2-diabetes-quiz#1)
* [ Ankylosing Spondylitis Pain: Fact or Fiction ](/articles/complementary-therapies-for-as-quiz#1)
* Connect
* About Medical News Today
* [ Who We Are ](/about)
* [ Our Editorial Process ](/articles/process)
* [ Content Integrity ](/about/content-integrity)
* [ Conscious Language ](/about/conscious-language)
* Newsletters
* [ Sign Up ](/newsletter)
* Follow Us

[ Medical News Today  ](https://www.medicalnewstoday.com/)

* Health Conditions
* Health Products
* Discover
* Tools
* Connect

Subscribe

#  Tooth extraction aftercare: A how-to guide

![](//i0.wp.com/post.medicalnewstoday.com/wp-
content/uploads/sites/3/2019/12/christine-frank_mr.png?w=105&h=105)

Medically reviewed  by  Christine Frank, DDS  —  By  Jon Johnson  on August
23, 2019

* Aftercare
* Multiple teeth
* Wisdom teeth
* Children
* Home remedies
* Seeing a dentist
* Summary

Tooth extraction involves completely removing a tooth from the mouth. People
may require tooth extraction for many reasons, ranging from tooth decay to
crowded teeth.

A dentist or dental surgeon will perform the extraction in their clinic and
then give the person some instructions for caring for the area as it heals.

During the appointment, the dental surgeon will inject a strong anesthetic
into the area around the tooth to prevent the person from feeling any pain.
They will then use a series of instruments to loosen the tooth before pulling
it out.

After removing the tooth, they will place gauze over the extraction site to
help control bleeding and promote clotting.

Learn more about tooth extraction aftercare in this article. We also provide a
general healing timeline and explain when to speak to a dentist.

##

Aftercare

![a-man-using-a-cold-compress-as-tooth-extraction-
aftercare](//i0.wp.com/post.medicalnewstoday.com/wp-
content/uploads/sites/3/2019/08/a-man-using-a-cold-compress-as-tooth-
extraction-aftercare-1024x732.jpg?w=1155&h=1650) [ Share on Pinterest
](https://www.pinterest.com/pin/create/button/?url=https%3A%2F%2Fwww.medicalnewstoday.com%2Farticles%2F326147&media=https%3A%2F%2Fpost.medicalnewstoday.com%2Fwp-
content%2Fuploads%2Fsites%2F3%2F2019%2F08%2Fa-man-using-a-cold-compress-as-
tooth-extraction-
aftercare-1024x732.jpg&description=Tooth%20extraction%20aftercare%3A%20Timeline%20and%20guide
"Share on Pinterest") Using a cold compress may help reduce pain after a tooth
extraction.

Aftercare for an extracted tooth can vary slightly depending on a few factors.

These include which tooth the dentist took out, as some teeth have deeper
roots than others and take longer to heal. However, most people find that pain
decreases after [ about 3 days ](https://dental.washington.edu/wp-
content/media/oral-surgery/Afteryouroralsurgery.pdf) .

One of the most important aspects of aftercare is maintaining the blood clot
that forms in the socket where the tooth used to be.

Caring for this blood clot is key to the healing process, and it helps prevent
painful complications, such as [ dry socket
](https://www.medicalnewstoday.com/articles/318202.php) .

###  Days 1–2

Much of the aftercare in the first couple of days following an extraction
focuses on allowing a blood clot to form and caring for the mouth in general.

As some experts  [ note ](https://www.bmj.com/content/357/bmj.j1217) , low
level bleeding for up to 24 hours after an extraction is perfectly normal.
However, active bleeding after this point requires treatment.

Here are a few additional tips for the first 2 days of aftercare:

* **Get plenty of rest** : Expect to be resting for at least the first 24 hours after the extraction.
* **Change the gauze as necessary** : It is important to leave the first gauze in the mouth for at least a few hours to allow the clot to form. After this, it is fine to change the gauze as often as necessary.
* **Avoid rinsing** : As tempting as it can be, avoid rinsing, swishing, or gargling anything in the mouth while the area is still clotting. These actions may dislodge any clot that is forming and affect the healing time.
* **Do not use straws** : Using a straw places a lot of pressure on the healing wound, which can easily dislodge the blood clot.
* **Do not spit** : Spitting also creates pressure in the mouth, which may dislodge the blood clot.
* **Avoid blowing the nose or sneezing** : If the surgeon removed a tooth from the upper half of the mouth, blowing the nose or sneezing can create pressure in the head that may dislodge the developing blood clot. Avoid blowing the nose and sneezing if possible.
* **Do not smoke** : Smoking creates the same pressure in the mouth as using a straw. While it is best to avoid smoking during the entire healing process, it is crucial not to smoke during the first couple of days as the blood clot forms.
* **Take pain relievers** : Over-the-counter pain relievers may help reduce pain and [ inflammation ](https://www.medicalnewstoday.com/articles/248423.php "Everything you need to know about inflammation") .
* **Use cold compresses** : Placing an ice pack or a towel-wrapped bag of ice on the area for 10–20 minutes at a time may help dull pain.
* **Elevate the head** : When sleeping, use extra pillows to elevate the head. Lying too flat may allow blood to pool in the head and prolong healing time.
* **Take any medications that the dentist recommends** : The dental surgeon may order prescription medications for complex removals. It is important to complete the full course of treatment.

###  Days 3–10

![a-woman-eating-soup](//i0.wp.com/post.medicalnewstoday.com/wp-
content/uploads/sites/3/2019/08/a-woman-eating-
soup-1024x683.jpg?w=1155&h=1541) [ Share on Pinterest
](https://www.pinterest.com/pin/create/button/?url=https%3A%2F%2Fwww.medicalnewstoday.com%2Farticles%2F326147&media=https%3A%2F%2Fpost.medicalnewstoday.com%2Fwp-
content%2Fuploads%2Fsites%2F3%2F2019%2F08%2Fa-woman-eating-
soup-1024x683.jpg&description=Tooth%20extraction%20aftercare%3A%20Timeline%20and%20guide
"Share on Pinterest") A person should try to eat soft foods while recovering
from tooth extraction.

After the clot has formed, it is vital to keep it securely in place and to
follow some extra steps for oral hygiene to help prevent other issues.

Tips for aftercare between the third and 10th day include:

* **Saline rinses** : When the clot is securely in place, gently rinse the mouth with a warm saline solution or a pinch of salt in warm water. This mixture helps kill bacteria in the mouth, which may prevent infections as the mouth heals.
* **Br…
"""

In [28]:
client = OpenAI(
    base_url="http://127.0.0.1:8080/v1",
    api_key="none"
)

response = client.chat.completions.create(
    model="local-model",
    messages=[
        {"role": "system", "content": SYSTEM_PROMPT},
        {"role": "user", "content": doc }
    ],
    extra_body={
        "chat_template_kwargs": {"enable_thinking": False}
    },
    temperature=0.1,
)

print("LFM2-1.2B-Extract-Q6_K: \n", response.choices[0].message.content)

LFM2-1.2B-Extract-Q6_K: 
 # Tooth extraction aftercare: A how-to guide

![](//i0.wp.com/post.medicalnewstoday.com/wp-
content/uploads/sites/3/2019/12/christine-frank_mr.png?w=105&h=105)

Medically reviewed  by  Christine Frank, DDS  —  By  Jon Johnson  on August
23, 2019

* Aftercare
* Multiple teeth
* Wisdom teeth
* Children
* Home remedies
* Seeing a dentist
* Summary

Tooth extraction involves completely removing a tooth from the mouth. People
may require tooth extraction for many reasons, ranging from tooth decay to
crowded teeth.

A dentist or dental surgeon will perform the extraction in their clinic and
then give the person some instructions for caring for the area as it heals.

During the appointment, the dental surgeon will inject a strong anesthetic
into the area around the tooth to prevent the person from feeling any pain.
They will then use a series of instruments to loosen the tooth before pulling
it out.

After removing the tooth, they will place gauze over the extraction

In [29]:
print("Qwen3-1.7B-Q8_0: \n", response.choices[0].message.content)

Qwen3-1.7B-Q8_0: 
 # Tooth extraction aftercare: A how-to guide

![](//i0.wp.com/post.medicalnewstoday.com/wp-
content/uploads/sites/3/2019/12/christine-frank_mr.png?w=105&h=105)

Medically reviewed  by  Christine Frank, DDS  —  By  Jon Johnson  on August
23, 2019

* Aftercare
* Multiple teeth
* Wisdom teeth
* Children
* Home remedies
* Seeing a dentist
* Summary

Tooth extraction involves completely removing a tooth from the mouth. People
may require tooth extraction for many reasons, ranging from tooth decay to
crowded teeth.

A dentist or dental surgeon will perform the extraction in their clinic and
then give the person some instructions for caring for the area as it heals.

During the appointment, the dental surgeon will inject a strong anesthetic
into the area around the tooth to prevent the person from feeling any pain.
They will then use a series of instruments to loosen the tooth before pulling
it out.

After removing the tooth, they will place gauze over the extraction site t

In [1]:
import pandas as pd
path = "data/BRIGHT/biology"
evals = pd.read_csv(f"{path}/evals.csv").to_dict(orient="records")
len(evals)

103